# NOWA Bank — Professional Banking Simulator

Professional Gradio version of the NOWA Bank project.

In [1]:
# NOWA Bank - Account Simulator

# ## Imports


import datetime
from decimal import Decimal, ROUND_DOWN
import gradio as gr


# ## Currency helpers
# 1 USD = 0.378 BHD (Bahraini Dinar is pegged to the US Dollar). USD is shown with 2 decimals, BHD with 3 decimals.


USD_TO_BHD = 0.378


def _currency_symbol(currency):
    return "$" if currency == "USD" else "BD"


def _currency_name(currency):
    return "USD" if currency == "USD" else "BHD"


def _decimals(currency):
    return 3 if currency == "BHD" else 2


def _truncate(value, decimals):
    """Cut a number down to `decimals` places WITHOUT rounding up.
    12.9999 -> 12.99 (never 13.00). We never want to credit/show the
    customer more than they actually typed."""
    quantum = Decimal(1).scaleb(-decimals)  # e.g. Decimal('0.01')
    d = Decimal(str(value)).quantize(quantum, rounding=ROUND_DOWN)
    return float(d)


def _to_usd(amount, currency):
    """Convert a user-entered amount from the selected currency to USD.
    The entered amount is first truncated to its own currency's
    decimals (2 for USD, 3 for BHD) so we only ever act on exactly what
    the user typed, then converted and truncated again in USD."""
    entered = _truncate(float(amount), _decimals(currency))
    if currency == "BHD":
        return _truncate(entered / USD_TO_BHD, 2)
    return entered


def _from_usd(amount_usd, currency):
    """Convert an internal USD amount to the selected display currency.
    Always truncates (never rounds up) so displayed amounts can't be
    higher than the real, stored value."""
    if currency == "BHD":
        return _truncate(float(amount_usd) * USD_TO_BHD, 3)
    return _truncate(float(amount_usd), 2)


def _format_money(amount_usd, currency):
    amount = _from_usd(amount_usd, currency)
    decimals = _decimals(currency)
    return f"{_currency_symbol(currency)}{amount:.{decimals}f} {_currency_name(currency)}"


def _format_amount_native(amount, currency):
    """Format an amount that is ALREADY in `currency` (e.g. exactly what
    the user typed, already truncated) - no USD round-trip involved.
    Converting BHD -> USD -> BHD to display a number back in the same
    currency it started in loses precision (0.378 doesn't divide evenly),
    e.g. 1.888 BHD could come back as 1.887. Use this instead whenever the
    display currency is the same currency the amount already is in."""
    decimals = _decimals(currency)
    return f"{_currency_symbol(currency)}{amount:.{decimals}f} {_currency_name(currency)}"


# ## Amount validation
# Only positive numbers are accepted. The `+` / `-` keys are also blocked in the browser (see the app cell below), 
# this is just the server-side check.


def _validate_amount(amount, currency="USD"):
    try:
        if amount is None or amount == "":
            return False, "Please enter an amount."

        if isinstance(amount, bool):
            return False, "Invalid amount."

        if not isinstance(amount, (int, float)):
            return False, "Amount must be a number."

        if isinstance(amount, float) and (amount != amount or amount in (float("inf"), float("-inf"))):
            return False, "Invalid amount."

        if amount < 0:
            return False, "Negative amounts are not allowed."

        # Truncate (never round up) to the currency's own decimals right
        # here, so 12.9999 USD is treated as exactly 12.99 everywhere
        # downstream - it can never become 13.00.
        amount = _truncate(float(amount), _decimals(currency))

        if amount <= 0:
            return False, "Amount must be greater than zero."

        return True, amount

    except Exception as e:
        return False, f"Could not validate the amount: {e}"


# ### Snap entered amount to the correct precision
# Gradio's `gr.Number(precision=...)` doesn't just limit the *display* 
# - it makes the **browser itself round** the value (e.g. `12.9999` -> `13.00`) the moment the field changes, 
# before our Python code ever runs. So the amount box below is created **without** `precision`, 
# and this function truncates (never rounds up) the raw value once the field loses focus, wired to the amount box's `blur` event.


def _snap_amount(amount, currency="USD"):
    """Cut the raw value from the amount box down to the correct number
    of decimals once the field loses focus - by truncation, not
    rounding, so e.g. 12.9999 becomes 12.99 and never 13.00."""
    try:
        if amount is None or amount == "":
            return gr.update()

        snapped = _truncate(float(amount), _decimals(currency))
        return gr.update(value=snapped)
    except (TypeError, ValueError):
        return gr.update()


# ### Add transaction
# Transactions are always stored in USD so switching currency never changes the real account value.


def _add_transaction(transactions, t_type, amount_usd, balance_after_usd):
    try:
        transactions = transactions + [{
            "type": t_type,
            "amount_usd": round(float(amount_usd), 6),
            "balance_after_usd": round(float(balance_after_usd), 6),
            "timestamp": datetime.datetime.now().strftime("%Y-%m-%d %H:%M:%S"),
        }]
        return transactions
    except Exception:
        return transactions


def _fresh_session():
    initial_balance_usd = 500.0
    initial_transactions = _add_transaction([], "Deposit", initial_balance_usd, initial_balance_usd)
    return initial_balance_usd, initial_transactions


# # Banking functions


# ### Withdraw / Deposit
# Use the currently selected currency.


def withdraw(amount, balance_usd, transactions, currency="USD"):
    try:
        ok, result = _validate_amount(amount, currency)
        if not ok:
            return balance_usd, transactions, result, gr.update()

        amount_usd = _to_usd(result, currency)

        if amount_usd > float(balance_usd) + 1e-9:
            return (
                balance_usd,
                transactions,
                f"Insufficient funds. Current balance: {_format_money(balance_usd, currency)}",
                gr.update(),
            )

        new_balance_usd = round(float(balance_usd) - amount_usd, 6)
        transactions = _add_transaction(transactions, "Withdraw", amount_usd, new_balance_usd)

        msg = (
            f"Withdrawal successful. Amount debited: {_format_amount_native(result, currency)} | "
            f"New balance: {_format_money(new_balance_usd, currency)}"
        )
        return new_balance_usd, transactions, msg, gr.update(value=None)

    except Exception as e:
        return balance_usd, transactions, f"An unexpected error occurred while processing the withdrawal: {e}", gr.update()


def deposit(amount, balance_usd, transactions, currency="USD"):
    try:
        ok, result = _validate_amount(amount, currency)
        if not ok:
            return balance_usd, transactions, result, gr.update()

        amount_usd = _to_usd(result, currency)
        new_balance_usd = round(float(balance_usd) + amount_usd, 6)

        transactions = _add_transaction(transactions, "Deposit", amount_usd, new_balance_usd)

        msg = (
            f"Deposit successful. Amount credited: {_format_amount_native(result, currency)} | "
            f"New balance: {_format_money(new_balance_usd, currency)}"
        )
        return new_balance_usd, transactions, msg, gr.update(value=None)

    except Exception as e:
        return balance_usd, transactions, f"An unexpected error occurred while processing the deposit: {e}", gr.update()


# ### Check balance / mini statement / reset / toggle currency


def check_balance(balance_usd, currency="USD"):
    try:
        return f"Current account balance: **{_format_money(balance_usd, currency)}**"
    except Exception as e:
        return f"Could not retrieve the balance: {e}"


def mini_statement(transactions, tx_type="All", date_mode="All Dates", start_date=None, end_date=None, currency="USD"):
    try:
        if not transactions:
            return "No transactions yet."

        filtered = transactions

        if tx_type and tx_type != "All":
            filtered = [t for t in filtered if t["type"] == tx_type]

        # "All Dates" means no date restriction at all, regardless of what
        # (if anything) is typed in the start/end boxes.
        if date_mode != "Custom Range":
            start_date = None
            end_date = None

        start_dt = None
        end_dt = None

        if start_date not in (None, ""):
            try:
                start_dt = datetime.datetime.strptime(str(start_date).strip(), "%Y-%m-%d")
            except ValueError:
                return "Start date must be in YYYY-MM-DD format."

        if end_date not in (None, ""):
            try:
                end_dt = datetime.datetime.strptime(str(end_date).strip(), "%Y-%m-%d")
                # Include the whole end day, not just midnight.
                end_dt = end_dt + datetime.timedelta(days=1) - datetime.timedelta(seconds=1)
            except ValueError:
                return "End date must be in YYYY-MM-DD format."

        if start_dt and end_dt and start_dt > end_dt:
            return "Start date must be before the end date."

        # Defense in depth: the calendar widget already grays out and blocks
        # future days, but we double-check here in case a date ever reaches
        # this function some other way.
        today_end = datetime.datetime.now().replace(hour=23, minute=59, second=59, microsecond=0)
        if start_dt and start_dt > today_end:
            return "Start date cannot be in the future."
        if end_dt and end_dt > today_end:
            return "End date cannot be in the future."

        if start_dt:
            filtered = [
                t for t in filtered
                if datetime.datetime.strptime(t["timestamp"], "%Y-%m-%d %H:%M:%S") >= start_dt
            ]

        if end_dt:
            filtered = [
                t for t in filtered
                if datetime.datetime.strptime(t["timestamp"], "%Y-%m-%d %H:%M:%S") <= end_dt
            ]

        if not filtered:
            return "No transactions match the selected filters."

        currency_label = _currency_name(currency)
        symbol = _currency_symbol(currency)
        decimals = _decimals(currency)

        lines = [
            f"### Mini Statement — {currency_label}",
            "",
            f"| Type | Amount ({currency_label}) | Balance After ({currency_label}) | Timestamp |",
            "|---|---:|---:|---|",
        ]

        for t in reversed(filtered):
            amount_usd = t.get("amount_usd", t.get("amount", 0))
            balance_after_usd = t.get("balance_after_usd", t.get("balance_after", 0))

            amount = _from_usd(amount_usd, currency)
            balance_after = _from_usd(balance_after_usd, currency)
            sign = "+" if t["type"] == "Deposit" else "-"

            lines.append(
                f"| {t['type']} | {sign}{symbol}{amount:.{decimals}f} | "
                f"{symbol}{balance_after:.{decimals}f} | {t['timestamp']} |"
            )

        return "\n".join(lines)

    except Exception as e:
        return f"Could not build the statement: {e}"


def reset_account(currency="USD"):
    try:
        initial_balance_usd, initial_transactions = _fresh_session()
        return (
            initial_balance_usd,
            initial_transactions,
            f"Account has been reset to {_format_money(initial_balance_usd, currency)}.",
            "",
            gr.update(value=None, label=f"Enter Amount ({currency})"),
        )
    except Exception as e:
        return (
            500.0,
            [],
            f"Account reset encountered an issue, balance defaulted to {_format_money(500.0, currency)}: {e}",
            "",
            gr.update(value=None),
        )


def toggle_currency(currency, amount, transactions, tx_type="All", date_mode="All Dates", start_date=None, end_date=None):
    new_currency = "BHD" if currency == "USD" else "USD"
    label = f"Currency: {new_currency}"
    statement = mini_statement(transactions, tx_type, date_mode, start_date, end_date, new_currency)

    new_amount_value = None
    if amount not in (None, ""):
        try:
            amount_usd = _to_usd(float(amount), currency)
            new_amount_value = _from_usd(amount_usd, new_currency)
        except (TypeError, ValueError):
            new_amount_value = None

    amount_update = gr.update(
        value=new_amount_value,
        label=f"Enter Amount ({new_currency})",
    )

    return new_currency, label, statement, amount_update


# # Login / Exit
# `exit_app` clears the session (balance, ledger, currency, form fields) and shows a logged-out page with a way back to Login.


USERS = {
    "user1": "pass123",
    "user2": "pass456",
    "user3": "pass789",
    "user4": "pass101",
    "user5": "pass202",
    "user6": "pass303",
    "user7": "pass404",
}


def login(username, password):
    try:
        if username in USERS and USERS.get(username) == password:
            initial_balance_usd, initial_transactions = _fresh_session()
            return (
                gr.update(visible=False),
                gr.update(visible=True),
                "",
                initial_balance_usd,
                initial_transactions,
                "USD",
                gr.update(value="Currency: USD"),
                gr.update(value=None, label="Enter Amount (USD)"),
                "",
                "",
                gr.update(value=""),
                gr.update(value=""),
            )
        return (
            gr.update(visible=True),
            gr.update(visible=False),
            "Invalid User ID or Password.",
            gr.update(), gr.update(), gr.update(), gr.update(),
            gr.update(), gr.update(), gr.update(), gr.update(),
            gr.update(value=""),
        )
    except Exception as e:
        return (
            gr.update(visible=True),
            gr.update(visible=False),
            f"Login error: {e}",
            gr.update(), gr.update(), gr.update(), gr.update(),
            gr.update(), gr.update(), gr.update(), gr.update(), gr.update(),
        )


def exit_app():
    initial_balance_usd, initial_transactions = _fresh_session()
    return (
        gr.update(visible=False),   # login page
        gr.update(visible=False),   # main page
        gr.update(visible=True),    # exit page
        gr.update(visible=False),   # top bar
        "",                         # status text
        initial_balance_usd,        # balance -> cleared
        initial_transactions,       # transactions -> cleared
        "USD",                      # currency -> reset
        gr.update(value="Currency: USD"),
        gr.update(value=None, label="Enter Amount (USD)"),
        "",                         # message -> cleared
        "",                         # statement -> cleared
        gr.update(value=""),        # username -> cleared
        gr.update(value=""),        # password -> cleared
    )


def return_to_login():
    return (
        gr.update(visible=True),    # login page
        gr.update(visible=False),   # exit page
        gr.update(visible=True),    # top bar
        "",                         # login message
    )


# # Brand logo
# Embedded as base64 so the app has no external image dependency.


LOGO_DATA_URI = "..."


# # Theme and styling


BRAND_THEME = gr.themes.Soft(
    primary_hue="red",
    secondary_hue="teal",
    neutral_hue="slate",
    font=[gr.themes.GoogleFont("Inter"), "Segoe UI", "Arial", "sans-serif"],
)

CUSTOM_CSS = """
@import url('https://fonts.googleapis.com/css2?family=DM+Sans:wght@400;500;600;700&family=Playfair+Display:wght@500;600;700&display=swap');
:root{
 --deep:#062b2e;--dark:#031c1f;--teal:#0d5558;--teal2:#176f70;--red:#b51f25;
 --muted:#718486;--border:#dfe7e5;--bg:#f4f7f6;--white:#fff;
 --shadow:0 24px 70px rgba(3,28,31,.12)
}
*{font-family:'DM Sans','Segoe UI',Arial,sans-serif!important;box-sizing:border-box}
body{margin:0!important;background:var(--bg)!important}
.gradio-container{max-width:none!important;min-height:100vh!important;padding:0!important;background:var(--bg)!important}
footer{display:none!important}
#top-bar{position:fixed!important;top:24px;right:28px;z-index:50;width:auto!important;margin:0!important}
#exit-corner{min-width:92px!important;border:0!important;background:var(--deep)!important;color:#fff!important;border-radius:999px!important;font-weight:700!important;backdrop-filter:blur(14px);box-shadow:none!important}
#exit-corner:hover{background:rgba(255,255,255,.16)!important}
#status-text{display:none!important}

/* LOGIN */
#login-page{min-height:100vh!important;width:100%!important;margin:0!important;padding:0!important;border:0!important;border-radius:0!important;background:transparent!important;box-shadow:none!important;overflow:hidden!important}
#login-shell{min-height:100vh;display:grid;grid-template-columns:1.08fr .92fr;background:var(--dark)}
#login-brand{position:relative;min-height:100vh;overflow:hidden;background:linear-gradient(145deg,#031c1f,#07373a 52%,#0a4b4d);color:#fff;display:flex;align-items:flex-end;padding:64px}
#login-brand:before{content:'';position:absolute;inset:0;background-image:url("...");background-size:cover;background-position:center;opacity:.38}
#login-brand:after{content:'';position:absolute;inset:0;background:linear-gradient(180deg,rgba(3,28,31,.08),rgba(3,28,31,.92))}
#login-brand .login-brand-content{position:relative;z-index:2;max-width:560px}
.login-mark{width:92px;height:92px;border-radius:24px;object-fit:cover;margin-bottom:28px;border:1px solid rgba(255,255,255,.18);box-shadow:0 18px 50px rgba(0,0,0,.25)}
.login-kicker{letter-spacing:.22em;text-transform:uppercase;font-size:12px;color:#a7d4d0;font-weight:800;margin-bottom:14px}
.login-brand-title{font-family:'Playfair Display',Georgia,serif!important;font-size:clamp(46px,6vw,76px);line-height:.98;margin:0 0 18px;color:#fff!important}
.login-brand-copy{color:rgba(255,255,255,.78);font-size:16px;line-height:1.7;max-width:470px}
#login-form-panel{min-height:100vh;background:#fbfcfb;display:flex;align-items:center;justify-content:center;padding:48px}
.login-form{width:min(430px,100%)}
.login-logo-small{width:68px;height:68px;border-radius:18px;object-fit:cover;margin-bottom:28px}
.login-eyebrow{color:var(--red);text-transform:uppercase;letter-spacing:.18em;font-size:11px;font-weight:800}
#brand-title{text-align:left!important;margin:8px 0!important;color:var(--deep)!important}
#brand-title h1{font-family:'Playfair Display',Georgia,serif!important;font-size:40px!important;font-weight:600!important}
#brand-subtitle{text-align:left!important;color:var(--muted)!important;margin-bottom:30px!important}
#login-page label,#main-page label{color:var(--deep)!important;font-weight:700!important;font-size:12px!important}
#login-page input,#main-page input,#main-page textarea,#main-page select{border:1px solid var(--border)!important;border-radius:14px!important;background:#fff!important;min-height:50px!important;box-shadow:none!important}
#login-page input:focus,#main-page input:focus,#main-page textarea:focus{border-color:var(--teal2)!important;box-shadow:0 0 0 4px rgba(23,111,112,.1)!important}
#login-btn{width:100%!important;min-height:52px!important;margin-top:8px!important;background:var(--deep)!important;color:#fff!important;border:0!important;border-radius:14px!important;font-weight:800!important}
#login-btn:hover{background:var(--teal)!important;transform:translateY(-1px)}

/* DASHBOARD */
#main-page{width:min(1180px,calc(100% - 48px))!important;margin:34px auto 48px!important;padding:0!important;border:0!important;border-radius:28px!important;background:#f7faf9!important;box-shadow:var(--shadow)!important;overflow:hidden!important}
.dashboard-shell{padding:30px 34px 0}
.dashboard-header{display:flex;justify-content:space-between;align-items:center;gap:20px;padding-bottom:26px;border-bottom:1px solid var(--border)}
.dashboard-brand{display:flex;align-items:center;gap:14px}
.dashboard-logo{width:50px;height:50px;border-radius:15px;object-fit:cover}
.dashboard-bank-name{color:var(--deep);font-family:'Playfair Display',Georgia,serif!important;font-size:28px;font-weight:600}
.dashboard-welcome{color:var(--muted);font-size:13px}
#currency-area{align-items:flex-end!important;padding:0 34px!important}
#currency-btn{background:#fff!important;color:var(--deep)!important;border:1px solid var(--border)!important;border-radius:999px!important;min-width:150px!important;font-weight:800!important}
.balance-card{margin-top:28px;border-radius:24px;padding:30px;background:linear-gradient(135deg,#062b2e,#0b5153);color:#fff;position:relative;overflow:hidden}
.balance-card:after{content:'';position:absolute;width:280px;height:280px;right:-90px;top:-120px;border-radius:50%;border:1px solid rgba(255,255,255,.14);box-shadow:0 0 0 28px rgba(255,255,255,.035),0 0 0 58px rgba(255,255,255,.025)}
.balance-label{position:relative;z-index:2;text-transform:uppercase;letter-spacing:.16em;font-size:11px;color:rgba(255,255,255,.66);font-weight:800}
.balance-value{position:relative;z-index:2;font-family:'Playfair Display',Georgia,serif!important;font-size:clamp(38px,5vw,56px);line-height:1;margin:10px 0 8px;color:#fff!important}
.balance-note{position:relative;z-index:2;color:rgba(255,255,255,.68);font-size:13px}
.section-title{color:var(--deep);font-size:18px;font-weight:800;margin:30px 0 12px}
#main-page .gr-button{min-height:46px!important}
#deposit-card,#withdraw-card{background:#fff;border:1px solid var(--border);border-radius:20px;padding:20px}
.action-card-title{color:var(--deep);font-weight:800;margin-bottom:5px}
.action-card-copy{color:var(--muted);font-size:12px;line-height:1.5;margin-bottom:12px}
#deposit-btn{background:var(--red)!important;color:#fff!important;border:0!important;border-radius:12px!important;font-weight:800!important}
#withdraw-btn,#balance-btn,#statement-btn,#reset-btn{background:var(--deep)!important;color:#fff!important;border:0!important;border-radius:12px!important;font-weight:700!important}
#secondary-actions{padding:0 34px!important;margin-top:14px!important}
#message{margin:20px 34px 0!important;border-radius:14px!important;background:#fff!important;border:1px solid var(--border)!important}
#currency-note{color:var(--muted)!important;font-size:12px!important;margin:10px 34px!important}
#filters-card{margin:20px 34px 0!important;background:#fff;border:1px solid var(--border);border-radius:20px;padding:20px}
#statement{margin:20px 34px 34px!important;background:#fff!important;border:1px solid var(--border)!important;border-radius:20px!important;padding:20px!important;overflow-x:auto!important}
#statement table{width:100%!important;border-collapse:separate!important;border-spacing:0!important}
#statement th{background:var(--deep)!important;color:#fff!important;padding:13px!important;font-size:12px!important;text-align:left!important}
#statement td{padding:12px!important;border-bottom:1px solid var(--border)!important;font-size:12px!important}

/* EXIT */
#exit-page{min-height:100vh!important;width:100%!important;margin:0!important;padding:0!important;border:0!important;border-radius:0!important;background:var(--dark)!important;color:#fff!important;display:flex!important;align-items:center!important;justify-content:center!important;overflow:hidden!important}
#exit-shell{width:min(980px,calc(100% - 48px));display:grid;grid-template-columns:1fr 1fr;background:rgba(255,255,255,.055);border:1px solid rgba(255,255,255,.12);border-radius:30px;overflow:hidden;box-shadow:0 30px 100px rgba(0,0,0,.35)}
#exit-art{min-height:580px;background-image:url("...");background-size:cover;background-position:center;position:relative}
#exit-art:after{content:'';position:absolute;inset:0;background:linear-gradient(90deg,rgba(3,28,31,.08),rgba(3,28,31,.75))}
#exit-content{padding:64px;display:flex;flex-direction:column;justify-content:center}
.exit-mini-logo{width:70px;height:70px;border-radius:18px;object-fit:cover;margin-bottom:28px}
#exit-page .exit-title{color:#fff!important;text-align:left!important;margin:0 0 12px!important}
#exit-page .exit-title h1{font-family:'Playfair Display',Georgia,serif!important;font-size:clamp(34px,4vw,52px)!important;font-weight:600!important;line-height:1.05}
#exit-page .exit-message{color:rgba(255,255,255,.72)!important;text-align:left!important;line-height:1.8!important;font-size:14px!important}
#return-login-btn{margin-top:20px!important;background:#fff!important;color:var(--deep)!important;border:0!important;border-radius:999px!important;min-height:48px!important;font-weight:800!important}
#exit-brand{color:#a7d4d0!important;margin-top:18px!important;font-size:11px!important;letter-spacing:.16em;text-transform:uppercase}


#login-brand .login-kicker,#login-brand .login-brand-title,#login-brand .login-brand-copy{position:relative;z-index:2}
#login-brand .login-brand-title{display:block}
#login-form-panel>.wrap{width:100%!important}
#login-form-panel>.wrap>div{width:100%!important}
#exit-art .exit-art-img{width:100%;height:100%;min-height:580px;object-fit:cover;display:block;opacity:.82}
#exit-art{padding:0!important}
#exit-content{justify-content:center!important}

/* CALENDAR */
#start-date-box,#end-date-box{display:none!important}
#date-range-calendar-root{max-width:330px;margin:8px 0 0!important;background:#fff;border:1px solid var(--border);border-radius:16px;padding:14px;font-size:13px}
.ndr-header{display:flex;align-items:center;justify-content:space-between;margin-bottom:8px}
.ndr-header button{background:var(--deep);color:#fff;border:0;border-radius:8px;padding:5px 10px;cursor:pointer}
.ndr-header button:disabled{background:#ccd6d5;cursor:not-allowed}
.ndr-title{font-weight:800;color:var(--deep)}
.ndr-grid{display:grid;grid-template-columns:repeat(7,1fr);gap:4px;text-align:center}
.ndr-dow{font-size:10px;color:var(--muted);font-weight:800;padding-bottom:3px}
.ndr-day{padding:7px 0;border-radius:8px;cursor:pointer;color:var(--deep)}
.ndr-day:hover:not(.ndr-disabled):not(.ndr-empty){background:#edf4f3}
.ndr-day.ndr-disabled{color:#c3cccb;cursor:not-allowed}
.ndr-day.ndr-empty{visibility:hidden}
.ndr-day.ndr-selected{background:var(--red)!important;color:#fff!important}
.ndr-day.ndr-in-range{background:rgba(181,31,37,.1)}
.ndr-footer{display:flex;justify-content:space-between;align-items:center;margin-top:10px;font-size:11px;color:var(--muted)}
.ndr-footer button{background:transparent;border:1px solid var(--border);border-radius:999px;padding:4px 10px;cursor:pointer;color:var(--deep)}
@media(max-width:800px){
 #login-shell,#exit-shell{grid-template-columns:1fr}
 #login-brand{min-height:42vh;padding:34px}
 #login-form-panel{min-height:58vh;padding:34px 24px}
 #exit-art{min-height:300px}
 #exit-content{padding:36px 28px}
 #main-page{width:calc(100% - 20px)!important;margin:10px auto 24px!important;border-radius:20px!important}
 .dashboard-shell{padding:22px 18px 0}
 #currency-area,#secondary-actions,#currency-note,#message,#filters-card,#statement{margin-left:18px!important;margin-right:18px!important;padding-left:0!important;padding-right:0!important}
 #top-bar{top:14px;right:14px}
}
"""


HEAD_HTML = """
<script>
(function () {
    var blockedKeys = ["-", "+", "e", "E", "/", "*"];

    function attachGuard(el) {
        if (el.dataset.guarded) return;
        el.dataset.guarded = "1";

        el.addEventListener("keydown", function (e) {
            if (blockedKeys.indexOf(e.key) !== -1) {
                e.preventDefault();
            }
        });

        el.addEventListener("paste", function (e) {
            var clipboard = e.clipboardData || window.clipboardData;
            var text = clipboard ? clipboard.getData("text") : "";
            if (/[^0-9.]/.test(text)) {
                e.preventDefault();
            }
        });
    }

    function scan() {
        document.querySelectorAll("input[type=number]").forEach(attachGuard);
    }

    window.addEventListener("load", scan);
    // Gradio mounts/replaces inputs after the initial load (e.g. after
    // login), so keep watching the page for new number inputs.
    var observer = new MutationObserver(scan);
    observer.observe(document.documentElement, { childList: true, subtree: true });
})();

// ---- Custom date-range calendar (start/end pick, future days blocked) ----
(function () {
    function pad(n) { return n < 10 ? "0" + n : "" + n; }
    function fmt(d) { return d.getFullYear() + "-" + pad(d.getMonth() + 1) + "-" + pad(d.getDate()); }

    function todayMidnight() {
        var t = new Date();
        t.setHours(0, 0, 0, 0);
        return t;
    }

    // Writes into the hidden Gradio Textbox and fires the events Gradio's
    // frontend listens for, so the existing Python .change() handlers
    // (which already redraw the mini statement) pick it up automatically.
    function setGradioValue(elemId, value) {
        var wrap = document.getElementById(elemId);
        if (!wrap) return;
        var el = wrap.querySelector("textarea, input");
        if (!el) return;
        var proto = el.tagName === "TEXTAREA" ? window.HTMLTextAreaElement.prototype : window.HTMLInputElement.prototype;
        var setter = Object.getOwnPropertyDescriptor(proto, "value").set;
        setter.call(el, value);
        el.dispatchEvent(new Event("input", { bubbles: true }));
        el.dispatchEvent(new Event("change", { bubbles: true }));
    }

    var state = { start: null, end: null, viewYear: null, viewMonth: null };
    var MONTH_NAMES = ["January", "February", "March", "April", "May", "June",
        "July", "August", "September", "October", "November", "December"];

    function rangeLabel() {
        if (state.start && state.end) return state.start + " \u2192 " + state.end;
        if (state.start) return state.start + " \u2192 \u2026";
        return "No dates selected";
    }

    function render(root) {
        var today = todayMidnight();
        if (state.viewYear === null) {
            state.viewYear = today.getFullYear();
            state.viewMonth = today.getMonth();
        }
        var first = new Date(state.viewYear, state.viewMonth, 1);
        var startOffset = first.getDay();
        var daysInMonth = new Date(state.viewYear, state.viewMonth + 1, 0).getDate();
        var isCurrentMonth = (state.viewYear === today.getFullYear() && state.viewMonth === today.getMonth());

        var html = "";
        html += '<div class="ndr-header">';
        html += '<button type="button" id="ndr-prev">\u2039</button>';
        html += '<div class="ndr-title">' + MONTH_NAMES[state.viewMonth] + " " + state.viewYear + "</div>";
        html += '<button type="button" id="ndr-next"' + (isCurrentMonth ? " disabled" : "") + ">\u203a</button>";
        html += "</div>";
        html += '<div class="ndr-grid">';
        ["Su", "Mo", "Tu", "We", "Th", "Fr", "Sa"].forEach(function (d) {
            html += '<div class="ndr-dow">' + d + "</div>";
        });
        for (var i = 0; i < startOffset; i++) html += '<div class="ndr-day ndr-empty"></div>';
        for (var day = 1; day <= daysInMonth; day++) {
            var d = new Date(state.viewYear, state.viewMonth, day);
            var dstr = fmt(d);
            var disabled = d > today; // only today and earlier are pickable
            var cls = "ndr-day";
            if (disabled) cls += " ndr-disabled";
            if (state.start === dstr || state.end === dstr) cls += " ndr-selected";
            else if (state.start && state.end && dstr > state.start && dstr < state.end) cls += " ndr-in-range";
            html += '<div class="' + cls + '" data-date="' + dstr + '">' + day + "</div>";
        }
        html += "</div>";
        html += '<div class="ndr-footer"><span>' + rangeLabel() + '</span><button type="button" id="ndr-clear">Clear</button></div>';

        root.innerHTML = html;

        root.querySelector("#ndr-prev").addEventListener("click", function () {
            state.viewMonth--;
            if (state.viewMonth < 0) { state.viewMonth = 11; state.viewYear--; }
            render(root);
        });
        var nextBtn = root.querySelector("#ndr-next");
        if (nextBtn) {
            nextBtn.addEventListener("click", function () {
                if (nextBtn.disabled) return;
                state.viewMonth++;
                if (state.viewMonth > 11) { state.viewMonth = 0; state.viewYear++; }
                render(root);
            });
        }
        root.querySelector("#ndr-clear").addEventListener("click", function () {
            state.start = null;
            state.end = null;
            setGradioValue("start-date-box", "");
            setGradioValue("end-date-box", "");
            render(root);
        });

        root.querySelectorAll(".ndr-day:not(.ndr-disabled):not(.ndr-empty)").forEach(function (cell) {
            cell.addEventListener("click", function () {
                var dstr = cell.getAttribute("data-date");
                if (!state.start || (state.start && state.end)) {
                    // Start a fresh selection.
                    state.start = dstr;
                    state.end = null;
                } else if (dstr < state.start) {
                    // Clicked before the current start -> it becomes the new start.
                    state.start = dstr;
                    state.end = null;
                } else {
                    state.end = dstr;
                }
                setGradioValue("start-date-box", state.start || "");
                setGradioValue("end-date-box", state.end || "");
                render(root);
            });
        });
    }

    function scan() {
        var root = document.getElementById("date-range-calendar-root");
        if (root && !root.dataset.ndrInit) {
            root.dataset.ndrInit = "1";
            render(root);
        }
    }

    window.addEventListener("load", scan);
    var ndrObserver = new MutationObserver(scan);
    ndrObserver.observe(document.documentElement, { childList: true, subtree: true });
})();
</script>
"""


# # App

def bank_account_simulator():
    with gr.Blocks(title="NOWA Bank", analytics_enabled=False) as app:
        with gr.Row(elem_id="top-bar") as top_bar:
            exit_button = gr.Button("Exit", elem_id="exit-corner", size="sm")
        status_text = gr.Markdown("", elem_id="status-text")

        # PAGE 3 — Exit
        with gr.Group(visible=False, elem_id="exit-page") as exit_page:
            with gr.Row(elem_id="exit-shell"):
                with gr.Column(elem_id="exit-art"):
                    gr.HTML(f'<img src="{LOGO_DATA_URI}" class="exit-art-img" alt="NOWA Bank"/>')
                with gr.Column(elem_id="exit-content"):
                    gr.HTML(f'<img src="{LOGO_DATA_URI}" class="exit-mini-logo" alt="NOWA Bank"/>')
                    gr.Markdown("### Thank you for banking with NOWA.", elem_id="exit-title")
                    gr.Markdown(
                        "Your session has been securely closed.\n\n"
                        "We appreciate your trust in NOWA Bank and look forward to serving you again.",
                        elem_id="exit-message",
                    )
                    return_button = gr.Button("Return to Login", elem_id="return-login-btn", size="sm")
                    gr.Markdown("Secure • Trusted • Exceptional", elem_id="exit-brand")

        # PAGE 1 — Login
        with gr.Group(visible=True, elem_id="login-page") as login_page:
            with gr.Row(elem_id="login-shell"):
                with gr.Column(elem_id="login-brand"):
                    gr.HTML(f'<img src="{LOGO_DATA_URI}" class="login-mark" alt="NOWA Bank"/>')
                    gr.HTML('<div class="login-kicker">Private Banking • Bahrain</div>')
                    gr.HTML('<div class="login-brand-title">Banking, refined.</div>')
                    gr.HTML('<div class="login-brand-copy">A secure and modern banking experience designed around clarity, control and confidence.</div>')
                with gr.Column(elem_id="login-form-panel"):
                    with gr.Column(elem_classes=["login-form"]):
                        gr.HTML(f'<img src="{LOGO_DATA_URI}" class="login-logo-small" alt="NOWA Bank"/>')
                        gr.HTML('<div class="login-eyebrow">Welcome back</div>')
                        gr.Markdown("# NOWA Bank", elem_id="brand-title")
                        gr.Markdown("Sign in to access your secure account.", elem_id="brand-subtitle")
                        username_input = gr.Textbox(label="Username", placeholder="Enter your username", autofocus=True)
                        password_input = gr.Textbox(label="Password", type="password", placeholder="Enter your password")
                        login_button = gr.Button("Sign In", elem_id="login-btn")
                        login_message = gr.Markdown("")

        # PAGE 2 — Main dashboard
        with gr.Group(visible=False, elem_id="main-page") as main_page:
            gr.HTML(f"""<div class="dashboard-shell">
                <div class="dashboard-header">
                    <div class="dashboard-brand">
                        <img src="{LOGO_DATA_URI}" class="dashboard-logo" alt="NOWA Bank"/>
                        <div><div class="dashboard-bank-name">NOWA Bank</div><div class="dashboard-welcome">Secure account management</div></div>
                    </div>
                </div>
                <div class="balance-card">
                    <div class="balance-label">Available Balance</div>
                    <div class="balance-value">$500.00 USD</div>
                    <div class="balance-note">Your balance updates after every transaction.</div>
                </div>
                <div class="section-title">Move your money</div>
            </div>""")
            with gr.Row(elem_id="main-header"):
                with gr.Column(elem_id="currency-area"):
                    currency_button = gr.Button("Currency: USD", elem_id="currency-btn", size="sm")

            initial_balance_usd, initial_transactions = _fresh_session()
            balance = gr.State(initial_balance_usd)
            transactions = gr.State(initial_transactions)
            currency = gr.State("USD")

            amount = gr.Number(label="Enter Amount (USD)", value=None, minimum=0)
            amount.blur(fn=_snap_amount, inputs=[amount, currency], outputs=[amount])
            gr.Markdown("USD ↔ BHD • USD uses 2 decimals; BHD uses 3 decimals. Only positive amounts are accepted.", elem_id="currency-note")

            with gr.Row():
                with gr.Column(elem_id="deposit-card"):
                    gr.Markdown("Deposit", elem_classes=["action-card-title"])
                    gr.Markdown("Add funds to your account securely.", elem_classes=["action-card-copy"])
                    deposit_button = gr.Button("Deposit", elem_id="deposit-btn")
                with gr.Column(elem_id="withdraw-card"):
                    gr.Markdown("Withdraw", elem_classes=["action-card-title"])
                    gr.Markdown("Transfer funds out of your account.", elem_classes=["action-card-copy"])
                    withdraw_button = gr.Button("Withdraw", elem_id="withdraw-btn")

            with gr.Row(elem_id="secondary-actions"):
                balance_button = gr.Button("Check Balance", elem_id="balance-btn")
                statement_button = gr.Button("Mini Statement", elem_id="statement-btn")
                reset_button = gr.Button("Reset Account", elem_id="reset-btn")

            message = gr.Textbox(label="Transaction Status", interactive=False)

            with gr.Group(elem_id="filters-card"):
                gr.Markdown("Recent activity", elem_classes=["section-title"])
                with gr.Row():
                    tx_filter = gr.Dropdown(choices=["All", "Deposit", "Withdraw"], value="All", label="Transaction Type")
                    date_filter_mode = gr.Radio(choices=["All Dates", "Custom Range"], value="All Dates", label="Date Filter")
                with gr.Row(visible=False) as date_range_row:
                    start_date_input = gr.Textbox(label="Start Date", placeholder="YYYY-MM-DD", elem_id="start-date-box")
                    end_date_input = gr.Textbox(label="End Date", placeholder="YYYY-MM-DD", elem_id="end-date-box")
                    gr.HTML('<div id="date-range-calendar-root"></div>')

            statement = gr.Markdown(elem_id="statement")

            currency_button.click(fn=toggle_currency, inputs=[currency, amount, transactions, tx_filter, date_filter_mode, start_date_input, end_date_input], outputs=[currency, currency_button, statement, amount])
            deposit_button.click(fn=deposit, inputs=[amount, balance, transactions, currency], outputs=[balance, transactions, message, amount])
            withdraw_button.click(fn=withdraw, inputs=[amount, balance, transactions, currency], outputs=[balance, transactions, message, amount])
            balance_button.click(fn=check_balance, inputs=[balance, currency], outputs=message)
            statement_button.click(fn=mini_statement, inputs=[transactions, tx_filter, date_filter_mode, start_date_input, end_date_input, currency], outputs=statement)
            tx_filter.change(fn=mini_statement, inputs=[transactions, tx_filter, date_filter_mode, start_date_input, end_date_input, currency], outputs=statement)
            date_filter_mode.change(fn=lambda mode: gr.update(visible=(mode == "Custom Range")), inputs=[date_filter_mode], outputs=[date_range_row])
            date_filter_mode.change(fn=mini_statement, inputs=[transactions, tx_filter, date_filter_mode, start_date_input, end_date_input, currency], outputs=statement)
            start_date_input.change(fn=mini_statement, inputs=[transactions, tx_filter, date_filter_mode, start_date_input, end_date_input, currency], outputs=statement)
            end_date_input.change(fn=mini_statement, inputs=[transactions, tx_filter, date_filter_mode, start_date_input, end_date_input, currency], outputs=statement)
            reset_button.click(fn=reset_account, inputs=[currency], outputs=[balance, transactions, message, statement, amount])

        login_button.click(fn=login, inputs=[username_input, password_input],
            outputs=[login_page, main_page, login_message, balance, transactions, currency, currency_button, amount, message, statement, username_input, password_input])
        exit_button.click(fn=exit_app, inputs=[],
            outputs=[login_page, main_page, exit_page, top_bar, status_text, balance, transactions, currency, currency_button, amount, message, statement, username_input, password_input])
        return_button.click(fn=return_to_login, inputs=[],
            outputs=[login_page, exit_page, top_bar, login_message])
    return app


if __name__ == "__main__":
    try:
        app = bank_account_simulator()
        app.launch(theme=BRAND_THEME, css=CUSTOM_CSS, head=HEAD_HTML)
    except Exception as e:
        print(f"Failed to launch the Bank Account Simulator: {e}")


c:\Users\Noor\AppData\Local\Programs\Python\Python313\Lib\site-packages\tqdm\auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm


* Running on local URL:  http://127.0.0.1:7860
* To create a public link, set `share=True` in `launch()`.
